In [1]:
# Getting imports and the model setup
import os
import sys
sys.path.insert(0, "../examples/open_deep_research")
import yaml
import importlib.resources
from smolagents import OpenAIModel, InferenceClientModel, LogLevel

from dotenv import load_dotenv
load_dotenv()

# Env overrides so one notebook can drive several parallel sweeps (see RUNS.md).
# "gpt-4o" | "gpt-5.4-mini" | "Qwen/Qwen3.7-Plus" | "Qwen/Qwen3.5-9B"
model_name = os.getenv("SMOLAGENTS_MODEL", "gpt-5.4-mini")
RUN_TAG = os.getenv("SMOLAGENTS_RUN_TAG", "_fixedbrowser")
N_QUESTIONS = int(os.getenv("SMOLAGENTS_N_QUESTIONS", "165"))
MAX_STEPS = int(os.getenv("SMOLAGENTS_MAX_STEPS", "50"))

enable_thinking = False  # hardcoded (was interactive input()) so this notebook can run headlessly via nbconvert

# build_tools reads this, so it must be set before the tools cell runs; an explicit env wins.
os.environ.setdefault("SMOLAGENTS_DOWNLOADS_DIR", f"downloads_naive{RUN_TAG}_{model_name.replace('/', '_')}")

if model_name in ["gpt-4o", "gpt-5.4-mini"]:
    model = OpenAIModel(
        model_id=model_name,
        api_key=os.environ["OPENAI_API_KEY"],
    )
elif model_name in ["Qwen/Qwen3.7-Plus", "Qwen/Qwen3.5-9B", "deepseek-ai/DeepSeek-R1", "openai/gpt-oss-120b"]:
    # Together requires enable_thinking nested inside chat_template_kwargs for vLLM-served open-weight
    # models -- a bare top-level enable_thinking happened to also work for Qwen3.7-Plus but was silently
    # ignored for Qwen3.5-9B. Verified chat_template_kwargs works correctly (both True and False) for both.
    # client_kwargs timeout bounds a single API call so a stalled/hanging stream fails within 5 minutes
    # instead of hanging indefinitely -- evaluate_agent already catches and records such errors.
    model = OpenAIModel(
        model_id=model_name,
        api_base="https://api.together.ai/v1/", # Leave this blank to query OpenAI servers.
        api_key=os.environ["TOGETHER_API_KEY"], # Switch to the API key for the server you're targeting.
        extra_body={"chat_template_kwargs": {"enable_thinking": enable_thinking}},
        client_kwargs={"timeout": 300.0},
    )
print(f"Using model: {model_name} with thinking enabled: {enable_thinking}")

Using model: gpt-5.4-mini with thinking enabled: False


In [2]:
# Debug check: fail loudly the moment any step returns reasoning despite enable_thinking=False,
# rather than only noticing it later by eyeballing console output.
from common_setup import assert_no_reasoning

/Users/poorvag/Work/smolagents/.venv/lib/python3.14/site-packages/pydub/utils.py:170: RuntimeWarning: Couldn't find ffmpeg or avconv - defaulting to ffmpeg, but may not work
  warn("Couldn't find ffmpeg or avconv - defaulting to ffmpeg, but may not work", RuntimeWarning)


In [3]:
# Getting the tools setup and the agent setup
from smolagents import CodeAgent
from smolagents.monitoring import LogLevel
from common_setup import build_tools

tools, ti_tool, visualizer = build_tools(model)

agent = CodeAgent(
    tools=tools,
    model=model,
    max_steps=MAX_STEPS,
    verbosity_level=LogLevel.DEBUG,
    additional_authorized_imports=["pandas", "numpy", "PIL", "json", "io", "zipfile", "csv", "openpyxl"],
    stream_outputs=("deepseek" in model_name) or ("Qwen" in model_name),
    step_callbacks=[assert_no_reasoning] if not enable_thinking else None,
)

web_search: LeakFilteredDuckDuckGoSearchTool at 0.25 q/s


In [4]:
# Load GAIA validation set from HuggingFace
# Visit https://huggingface.co/datasets/gaia-benchmark/GAIA to request access first
import pandas as pd
from common_setup import load_gaia_dataset

SET_TO_RUN = "validation"
eval_ds = load_gaia_dataset(set_to_run=SET_TO_RUN)

print(f"Loaded {len(eval_ds)} examples")
print(pd.DataFrame(eval_ds)["task"].value_counts())

Note: Environment variable`HF_TOKEN` is set and is the current active token independently from the token you've just configured.


Loaded 165 examples
task
2    86
1    53
3    26
Name: count, dtype: int64


**Note on token counts below:** `step.token_usage` is per-step (that single LLM call's own `input_tokens`/`output_tokens`, taken straight from the API's `usage` field), not a running total. Because the full step history is resent every call, `input_tokens` still grows step-over-step on its own — it's just not incremental. This differs from the smolagents console trajectory (and `agent.monitor.get_total_token_counts()`), which print a *cumulative sum* of each step's `token_usage` and will not match these per-step prints after step 1. See the "Token usage accounting" section in CLAUDE.md for details.

In [5]:
# Scoring + eval loop now live in common_setup.py, shared with markovReAct.ipynb
from common_setup import evaluate_agent, question_scorer

In [6]:
print(model.kwargs)
print(agent.model.kwargs)
print(agent.model is model)

{}
{}
True


In [7]:
RUN_NAME = f"naive_react_{model_name}_{enable_thinking}{RUN_TAG}"
print(f"run: {RUN_NAME}  (leak filter: {os.getenv('SMOLAGENTS_FILTER_LEAKS', '1')})")

results = evaluate_agent(
    agent,
    eval_ds,
    ti_tool,
    visualizer,
    n_samples=N_QUESTIONS,
    output_file=f"{RUN_NAME}.jsonl",
    pickle_dir=RUN_NAME,
)

run: naive_react_gpt-5.4-mini_False_rerun_emptycode  (leak filter: 1)
leak-filter drops logged to: naive_react_gpt-5.4-mini_False_rerun_emptycode_leakdrops.jsonl

[1/165] A paper about AI regulation that was originally submitted to arXiv.org in June 2022 shows a figure w...


╭──────────────────────────────────────────────────── New run ────────────────────────────────────────────────────╮
│                                                                                                                 │
│ A paper about AI regulation that was originally submitted to arXiv.org in June 2022 shows a figure with three   │
│ axes, where each axis has a label word at both ends. Which of these words is used to describe a type of society │
│ in a Physics and Society article submitted to arXiv.org on August 11, 2016?                                     │
│                                                                                                                 │
╰─ OpenAIModel - gpt-5.4-mini ────────────────────────────────────────────────────────────────────────────────────╯

━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ Step 1 ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━

Output message of the LLM: ────────────────────────────────────────────────────────────────────────────────────────
I’ll need to inspect the June 2022 arXiv paper’s figure labels and then find which of those words appears in the   
August 11, 2016 Physics and Society article.                                                                       
                                                                                                                   
<code>                                                                                                             
# Search for the June 2022 AI regulation paper on arXiv                                                            
results = web_search(query="site:arxiv.org June 2022 AI regulation paper figure three axes labels arXiv")          
print(results)                                                                                                     
                                                                                                                   

─ Executing parsed code: ──────────────────────────────────────────────────────────────────────────────────────── 
  # Search for the June 2022 AI regulation paper on arXiv                                                          
  results = web_search(query="site:arxiv.org June 2022 AI regulation paper figure three axes labels arXiv")        
  print(results)                                                                                                   
 ─────────────────────────────────────────────────────────────────────────────────────────────────────────────────

...

Output message of the LLM: ────────────────────────────────────────────────────────────────────────────────────────
Thought: The record page shows the last pre-June-7-2023 Mario Kart Stadium WR as 1'34"359 on 2023-04-29, and the   
next change is 2023-08-02. So the world record time as of June 7, 2023 was 1:34.359.                               
                                                                                                                   
<code>                                                                                                             
final_answer("1:34.359")                                                                                           
                                                                                                                   

─ Executing parsed code: ──────────────────────────────────────────────────────────────────────────────────────── 
  final_answer("1:34.359")                                                                                         
 ─────────────────────────────────────────────────────────────────────────────────────────────────────────────────

Final answer: 1:34.359

[Step 22: Duration 1.94 seconds| Input tokens: 222,479 | Output tokens: 2,675]

  ✗ | 102.5s | 22 steps | tokens: TokenUsage(input_tokens=222479, output_tokens=2675, total_tokens=225154)
    Expected: 1:41.614
    Got:      1:34.359


In [8]:
df = pd.DataFrame(results)
total = len(df)
correct = df["is_correct"].sum()

print(f"=== GAIA Evaluation Results ===")
print(f"Overall accuracy:   {correct}/{total} = {correct/total:.1%}")
print(f"Avg time per question: {df['time_taken_seconds'].mean():.1f}s")
print(f"Avg steps per question: {df['num_steps'].mean():.1f}")

total_tokens = df["token_counts"].apply(lambda x: x.get("total_tokens", 0)).mean()
print(f"Total tokens used:  {total_tokens:,}")

print(f"\nAccuracy by level:")
for level in sorted(df["task"].unique()):
    level_df = df[df["task"] == level]
    lc = level_df["is_correct"].sum()
    lt = len(level_df)
    print(f"  Level {level}: {lc}/{lt} = {lc/lt:.1%}")

print(f"\nTool usage (total calls across all questions):")
tool_usage_df = pd.DataFrame(df["tool_usage"].tolist()).sum().sort_values(ascending=False)
for tool, count in tool_usage_df.items():
    if count > 0:
        print(f"  {tool}: {int(count)}")

=== GAIA Evaluation Results ===
Overall accuracy:   56/165 = 33.9%
Avg time per question: 372.2s
Avg steps per question: 5.8
Total tokens used:  29,779.60606060606

Accuracy by level:
  Level 1: 25/53 = 47.2%
  Level 2: 28/86 = 32.6%
  Level 3: 3/26 = 11.5%

Tool usage (total calls across all questions):
  web_search: 260
  final_answer: 176
  visit_page: 132
  find_on_page_ctrl_f: 54
  inspect_file_as_text: 19
  page_down: 11
  find_archived_url: 7
  visualizer: 5
  find_next: 3
  page_up: 1
